# Model explainability and attribution stability

This notebook is the human-facing explainability workflow. It answers the half of
**secondary research question 2** that the held-out model evaluation left open: are feature-attribution patterns
consistent across DFCI, MSK, and VICC, and between OS and TTNT-D, after accounting for de novo
versus recurrent presentation and previous oxaliplatin exposure?

Every explanation here describes **model behaviour and prognostic association**, never
biological mechanism, causation, or treatment effect. The primary explanation horizon is
**730 days**, chosen prospectively on event support, matching the exploratory optimization's primary target.

This workflow explains models under a frozen four-tier **model-availability hierarchy**
(`explainability-spec.md`): `minimal_cox` is the primary, reliable reference; the corrected
Python `elastic_net_cox` and `spline_cox` are the comparison set; R `glmnet` and the two
Workstream B Python candidates are exploratory supplementary; `flexsurv_rp_spline` and
`core_cox` are recorded but **not explained**, for fit instability. Comparisons are made only
across scopes where the compared models fitted successfully -- an apparent attribution
difference that coincides with a missing centre or a failed fit is reported as an
**availability artifact**, never as biological or institutional heterogeneity.

In [1]:
from pathlib import Path

import pandas as pd
from IPython.display import display

PROJECT_ROOT = Path.cwd()
if PROJECT_ROOT.name == "notebooks":
    PROJECT_ROOT = PROJECT_ROOT.parent
ANALYSIS_DIRECTORY = PROJECT_ROOT / "analysis" / "out" / "current"
FEATURE_MANIFEST_PATH = PROJECT_ROOT / "src" / "crc_folfox" / "features" / "feature_manifest.json"

pd.set_option("display.max_rows", 200)
pd.set_option("display.width", 160)

## Model-availability hierarchy

Published **before** any explanation value exists, so the hierarchy that governs every later
section is visible ahead of the results it constrains. `model_availability.csv` carries every
model's tier, source registry, feature set, runtime, and -- for the two Tier 4 models -- its
recorded not-explained reason and real fit-success counts.

In [2]:
from crc_folfox.explain.contracts import MODEL_REGISTER

registry_labels = {
    "frozen_model_training": "frozen model-training results",
    "corrected_model_training": "corrected model-training results",
    "exploratory_optimization": "exploratory optimization results",
}
availability_preview = pd.DataFrame(
    [
        {
            "model": r.model_name,
            "tier": r.tier,
            "source_registry": registry_labels.get(r.source_registry, r.source_registry),
            "analysis_status": r.analysis_status,
            "feature_set": r.feature_set,
            "runtime": r.runtime,
            "not_explained_reason": r.not_explained_reason or "",
            "fit_success_count": r.not_explained_fit_success_count,
            "fit_total_count": r.not_explained_fit_total_count,
        }
        for r in MODEL_REGISTER
    ]
)
display(availability_preview)

,model,tier,source_registry,analysis_status,feature_set,runtime,not_explained_reason,fit_success_count,fit_total_count
0,minimal_cox,primary_reference,frozen model-training results,primary,baseline,python,,NaN,NaN
1,spline_cox,comparison,frozen model-training results,primary,core,python,,NaN,NaN
2,elastic_net_cox,comparison,corrected model-training results,technical_correction,core,python,,NaN,NaN
3,glmnet_ridge_core,exploratory_supplementary,exploratory optimization results,post_hoc_exploratory,core,r,,NaN,NaN
4,glmnet_enet_core,exploratory_supplementary,exploratory optimization results,post_hoc_exploratory,core,r,,NaN,NaN
5,penalized_nonlinear_cox,exploratory_supplementary,exploratory optimization results,post_hoc_exploratory,core,python,,NaN,NaN
6,reduced_core_penalized_cox,exploratory_supplementary,exploratory optimization results,post_hoc_exploratory,core,python,,NaN,NaN
7,core_cox,not_explained,frozen model-training results,primary,core,python,fit_failed_singular_design,3.0,106.0
8,flexsurv_rp_spline,not_explained,exploratory optimization results,post_hoc_exploratory,baseline,r,fit_instability_explanation_unreliable,24.0,56.0


## Preflight: verified inputs and frozen-primary preservation

Both the model-level and aggregation workflows verify the cleaned-dataset and preprocessing artifacts,
the frozen model-training bundle, the Workstream A corrected bundle, and the Workstream B bundle before
computing anything, and proves the corrected-vs-frozen `minimal_cox`/`spline_cox` canonical-state
hash equality that makes Tier 1/Tier 2's mixed provenance safe. The aggregation call re-verifies
the frozen primary unchanged again after publication. These are the only two supported explainability
orchestration boundaries this notebook calls.

**2026-08-15:** the original single `run_explainability_workflow` call below was replaced by a
per-model split -- one model-level call per registered model, persisting each
model's aggregate-only results independently, followed by one aggregation call
call that combines them and publishes -- after the real full-inventory rerun was killed twice by
causes external to the code (a session/harness restart, then an overnight machine-sleep event) while
running as a single ~38-hour process. The split is what actually produced the published
`analysis/out/current/explainability/` bundle this notebook's later cells describe; see
`implement.md`'s "Per-model split and the corrected real inventory" for the full account. Both
functions return the same `ExplainabilityResult` shape as the original single-process call, so no
cell below this one needed to change.

In [4]:
from crc_folfox.explain.contracts import EXPLAINED_MODEL_NAMES
from crc_folfox.explain.workflow import (
    aggregate_explainability_results,
    run_model_explainability,
)

INTERMEDIATE_DIRECTORY = ANALYSIS_DIRECTORY / "explainability.intermediate"

for model_name in EXPLAINED_MODEL_NAMES:
    run_model_explainability(
        ANALYSIS_DIRECTORY, FEATURE_MANIFEST_PATH, model_name, INTERMEDIATE_DIRECTORY
    )

result = aggregate_explainability_results(
    ANALYSIS_DIRECTORY, FEATURE_MANIFEST_PATH, INTERMEDIATE_DIRECTORY
)

print(f"Explanation scopes: {len(result.scope_status)}")
print(result.scope_status["explanation_status"].value_counts().to_dict())

/Users/camilasarmiento/Documents/Data Freelancer/portfolio/CRC/.venv/lib/python3.12/site-packages/lifelines/fitters/coxph_fitter.py:1530: LinAlgWarning: An ill-conditioned matrix detected: slice 0 has rcond = 8.515729493995858e-17.
  inv_h_dot_g_T = spsolve(-h, g, assume_a="pos", check_finite=False)
/Users/camilasarmiento/Documents/Data Freelancer/portfolio/CRC/.venv/lib/python3.12/site-packages/lifelines/fitters/cox_time_varying_fitter.py:526: RuntimeWarning: overflow encountered in exp
  phi_i = weights_at_t * np.exp(np.dot(X_at_t, beta))
/Users/camilasarmiento/Documents/Data Freelancer/portfolio/CRC/.venv/lib/python3.12/site-packages/lifelines/fitters/cox_time_varying_fitter.py:526: RuntimeWarning: overflow encountered in exp
  phi_i = weights_at_t * np.exp(np.dot(X_at_t, beta))
/Users/camilasarmiento/Documents/Data Freelancer/portfolio/CRC/.venv/lib/python3.12/site-packages/lifelines/fitters/cox_time_varying_fitter.py:526: RuntimeWarning: overflow encountered in exp
  phi_i = weigh

Explanation scopes: 54
{'explained': 41, 'not_explained': 12, 'not_computable': 1}


## Tier 1 -- `minimal_cox`: the primary, reliable reference

This is the primary explainability deliverable. `minimal_cox` fitted in every real model-training scope, was
the competitive primary-evaluation result, and no exploratory optimization candidate showed `clear_added_value` against it
for the primary 730-day OS target. Its coefficients carry **model-based** standard errors and
95% confidence intervals (the only model for which that provenance is valid); its grouped
permutation importance is the common scale every later tier is compared against.

In [5]:
minimal_coefficients = result.coefficient_summary[
    result.coefficient_summary["model"] == "minimal_cox"
]
display(minimal_coefficients)

minimal_importance = result.importance_summary[
    (result.importance_summary["model"] == "minimal_cox")
    & (result.importance_summary["metric"] == "730")
]
display(minimal_importance)

minimal_cross_centre = result.attribution_stability[
    (result.attribution_stability["model_name"] == "minimal_cox")
    & (result.attribution_stability["comparison_type"] == "cross_centre")
]
display(minimal_cross_centre)

,endpoint,centre,model,explanation_tier,analysis_status,design_column,feature_group,coefficient,hazard_ratio,interval_provenance,standard_error,ci_lower,ci_upper
0,OS,DFCI,minimal_cox,primary_reference,primary,age_at_folfox,age_at_folfox,0.125724,1.133969,model_based,0.072607,-0.016583,0.268031
1,OS,DFCI,minimal_cox,primary_reference,primary,metastatic_presentation__De novo Stage IV,metastatic_presentation,0.690415,1.994544,model_based,0.181140,0.335388,1.045442
2,OS,DFCI,minimal_cox,primary_reference,primary,ca_d_site__C18.0,ca_d_site,0.295694,1.344058,model_based,0.214011,-0.123760,0.715147
3,OS,DFCI,minimal_cox,primary_reference,primary,ca_d_site__C18.2,ca_d_site,0.333111,1.395303,model_based,0.253752,-0.164233,0.830455
4,OS,DFCI,minimal_cox,primary_reference,primary,ca_d_site__C18.4,ca_d_site,-0.263869,0.768074,model_based,0.331982,-0.914542,0.386805
5,OS,DFCI,minimal_cox,primary_reference,primary,ca_d_site__C18.5,ca_d_site,0.337519,1.401466,model_based,0.431481,-0.508168,1.183205
6,OS,DFCI,minimal_cox,primary_reference,primary,ca_d_site__C18.6,ca_d_site,-0.109891,0.895932,model_based,0.308027,-0.713612,0.493830
7,OS,DFCI,minimal_cox,primary_reference,primary,ca_d_site__C18.7,ca_d_site,-0.174493,0.839882,model_based,0.199228,-0.564972,0.215986
8,OS,DFCI,minimal_cox,primary_reference,primary,ca_d_site__C18.9,ca_d_site,0.977235,2.657098,model_based,0.383599,0.225393,1.729076
9,OS,DFCI,minimal_cox,primary_reference,primary,ca_d_site__C19.9,ca_d_site,-0.047495,0.953615,model_based,0.258410,-0.553969,0.458979


,endpoint,centre,model,explanation_tier,analysis_status,feature_group,n_columns,metric,importance,finite_fraction,reporting_status
1,OS,DFCI,minimal_cox,primary_reference,primary,age_at_folfox,1,730,0.002129,1.0,estimable
4,OS,DFCI,minimal_cox,primary_reference,primary,metastatic_presentation,1,730,0.010953,1.0,estimable
7,OS,DFCI,minimal_cox,primary_reference,primary,ca_d_site,9,730,0.011532,1.0,estimable
10,OS,DFCI,minimal_cox,primary_reference,primary,number_metastatic_sites,1,730,0.005979,1.0,estimable
13,OS,MSK,minimal_cox,primary_reference,primary,age_at_folfox,1,730,0.002994,1.0,estimable
16,OS,MSK,minimal_cox,primary_reference,primary,metastatic_presentation,1,730,0.008362,1.0,estimable
19,OS,MSK,minimal_cox,primary_reference,primary,ca_d_site,8,730,0.005381,1.0,estimable
22,OS,MSK,minimal_cox,primary_reference,primary,number_metastatic_sites,1,730,0.007768,1.0,estimable
25,OS,VICC,minimal_cox,primary_reference,primary,age_at_folfox,1,730,0.002353,1.0,estimable
28,OS,VICC,minimal_cox,primary_reference,primary,metastatic_presentation,1,730,0.022793,1.0,estimable


,comparison_type,model_name,key_a,key_b,scope_basis,availability_confounded,availability_artifact_possible,comparison_status,reason,kendall_tau,top_k,topk_overlap,jaccard,top_k_boundary_tied,sign_agreement,n_groups,endpoint
0,cross_centre,minimal_cox,DFCI,MSK,identical_scopes,False,False,comparable,,0.333333,2,1.0,0.333333,False,1.0,4,OS
1,cross_centre,minimal_cox,DFCI,VICC,identical_scopes,False,False,comparable,,-0.333333,2,1.0,0.333333,False,1.0,4,OS
2,cross_centre,minimal_cox,MSK,VICC,identical_scopes,False,False,comparable,,0.333333,2,1.0,0.333333,False,1.0,4,OS
21,cross_centre,minimal_cox,DFCI,MSK,identical_scopes,False,False,comparable,,0.666667,2,1.0,0.333333,False,1.0,4,TTNT-D
22,cross_centre,minimal_cox,DFCI,VICC,identical_scopes,False,False,comparable,,0.333333,2,2.0,1.000000,False,1.0,4,TTNT-D
23,cross_centre,minimal_cox,MSK,VICC,identical_scopes,False,False,comparable,,0.000000,2,1.0,0.333333,False,1.0,4,TTNT-D


## Tier 2 -- corrected `elastic_net_cox` and `spline_cox`: the comparison set

`elastic_net_cox` is loaded from the **Workstream A corrected model-training** bundle (0/106
`fit_failed`), not the frozen original model-training bundle (10/106 `fit_failed`) -- explaining the defective
bundle would attribute a software failure to the data. Its rows carry
`analysis_status = technical_correction`. Neither model may report a model-based standard
error: both are penalized (a fixed nonzero penalty for `spline_cox`, a tuned one for
`elastic_net_cox`), so their uncertainty comes only from the labelled bootstrap refit
distribution.

In [6]:
tier2_models = ("spline_cox", "elastic_net_cox")
tier2_coefficients = result.coefficient_summary[
    result.coefficient_summary["model"].isin(tier2_models)
]
display(tier2_coefficients)

tier2_importance = result.importance_summary[
    result.importance_summary["model"].isin(tier2_models)
    & (result.importance_summary["metric"] == "730")
]
display(tier2_importance)

assert (tier2_coefficients["standard_error"].isna()).all(), "Tier 2 must carry no model-based SE"

,endpoint,centre,model,explanation_tier,analysis_status,design_column,feature_group,coefficient,hazard_ratio,interval_provenance,standard_error,ci_lower,ci_upper
65,OS,DFCI,spline_cox,comparison,primary,naaccr_sex_code__Male,naaccr_sex_code,-0.105760,0.899641,bootstrap_refit,NaN,-0.388732,0.189940
66,OS,DFCI,spline_cox,comparison,primary,"race_ethnicity__AAAPI (Asian, Asian American, ...",race_ethnicity,-0.029110,0.971310,bootstrap_refit,NaN,-0.702151,0.407218
67,OS,DFCI,spline_cox,comparison,primary,race_ethnicity__Hispanic/Latinx,race_ethnicity,-0.185688,0.830533,bootstrap_refit,NaN,-1.012516,0.467054
68,OS,DFCI,spline_cox,comparison,primary,race_ethnicity__Non-Hispanic Black,race_ethnicity,0.464602,1.591380,bootstrap_refit,NaN,-0.134187,0.995677
69,OS,DFCI,spline_cox,comparison,primary,race_ethnicity__Unknown,race_ethnicity,-0.209468,0.811016,bootstrap_refit,NaN,-1.237853,0.553528
...,...,...,...,...,...,...,...,...,...,...,...,...,...
434,TTNT-D,VICC,elastic_net_cox,comparison,technical_correction,dmets_liver,dmets_liver,0.685683,1.985127,bootstrap_refit,NaN,0.374209,1.021831
435,TTNT-D,VICC,elastic_net_cox,comparison,technical_correction,dmets_pelvis,dmets_pelvis,-0.160656,0.851585,bootstrap_refit,NaN,-0.471784,0.085850
436,TTNT-D,VICC,elastic_net_cox,comparison,technical_correction,dmets_thorax,dmets_thorax,0.460685,1.585160,bootstrap_refit,NaN,0.208956,0.759588
437,TTNT-D,VICC,elastic_net_cox,comparison,technical_correction,prior_oxaliplatin,prior_oxaliplatin,0.392433,1.480579,bootstrap_refit,NaN,-0.091321,0.986520


,endpoint,centre,model,explanation_tier,analysis_status,feature_group,n_columns,metric,importance,finite_fraction,reporting_status
73,OS,DFCI,spline_cox,comparison,primary,naaccr_sex_code,1,730,2.532966e-04,1.0,estimable
76,OS,DFCI,spline_cox,comparison,primary,race_ethnicity,5,730,-3.778735e-03,1.0,estimable
79,OS,DFCI,spline_cox,comparison,primary,metastatic_presentation,1,730,1.125502e-02,1.0,estimable
82,OS,DFCI,spline_cox,comparison,primary,crc_type,3,730,5.561652e-03,1.0,estimable
85,OS,DFCI,spline_cox,comparison,primary,ca_d_site,9,730,1.473821e-03,1.0,estimable
88,OS,DFCI,spline_cox,comparison,primary,ca_grade,3,730,6.374483e-03,1.0,estimable
91,OS,DFCI,spline_cox,comparison,primary,dmets_abdomen,1,730,5.231405e-03,1.0,estimable
94,OS,DFCI,spline_cox,comparison,primary,dmets_bone,1,730,3.520291e-04,1.0,estimable
97,OS,DFCI,spline_cox,comparison,primary,dmets_brain,1,730,-1.910122e-04,1.0,estimable
100,OS,DFCI,spline_cox,comparison,primary,dmets_liver,1,730,-3.010157e-04,1.0,estimable


## Tier 3 -- exploratory supplementary candidates

R `glmnet_ridge_core`/`glmnet_enet_core` and the two Python Workstream B candidates
(`penalized_nonlinear_cox`, `reduced_core_penalized_cox`) are **post hoc exploratory**: none
showed `clear_added_value` over `minimal_cox` for the primary 730-day OS target. Every row is
labelled `post_hoc_exploratory`, and no Tier 3 result is shown without the Tier 1 result for the
same quantity beside it.

In [7]:
tier3_models = (
    "glmnet_ridge_core",
    "glmnet_enet_core",
    "penalized_nonlinear_cox",
    "reduced_core_penalized_cox",
)
tier3_importance = result.importance_summary[
    result.importance_summary["model"].isin(tier3_models)
    & (result.importance_summary["metric"] == "730")
]
display(tier3_importance)

# Always shown beside its Tier 1 counterpart -- never presented alone.
combined_730 = result.importance_summary[result.importance_summary["metric"] == "730"]
display(combined_730[combined_730["model"].isin(("minimal_cox", *tier3_models))])

,endpoint,centre,model,explanation_tier,analysis_status,feature_group,n_columns,metric,importance,finite_fraction,reporting_status
613,OS,DFCI,glmnet_ridge_core,exploratory_supplementary,post_hoc_exploratory,age_at_folfox,1,730,0.000255,1.0,estimable
616,OS,DFCI,glmnet_ridge_core,exploratory_supplementary,post_hoc_exploratory,naaccr_sex_code,1,730,0.000136,1.0,estimable
619,OS,DFCI,glmnet_ridge_core,exploratory_supplementary,post_hoc_exploratory,race_ethnicity,5,730,-0.000632,1.0,estimable
622,OS,DFCI,glmnet_ridge_core,exploratory_supplementary,post_hoc_exploratory,metastatic_presentation,1,730,0.003114,1.0,estimable
625,OS,DFCI,glmnet_ridge_core,exploratory_supplementary,post_hoc_exploratory,crc_type,3,730,0.000739,1.0,estimable
...,...,...,...,...,...,...,...,...,...,...,...
1651,TTNT-D,VICC,reduced_core_penalized_cox,exploratory_supplementary,post_hoc_exploratory,dmets_liver,1,730,0.002906,1.0,estimable_imprecise
1654,TTNT-D,VICC,reduced_core_penalized_cox,exploratory_supplementary,post_hoc_exploratory,dmets_pelvis,1,730,0.001688,1.0,estimable_imprecise
1657,TTNT-D,VICC,reduced_core_penalized_cox,exploratory_supplementary,post_hoc_exploratory,dmets_thorax,1,730,0.015564,1.0,estimable_imprecise
1660,TTNT-D,VICC,reduced_core_penalized_cox,exploratory_supplementary,post_hoc_exploratory,prior_oxaliplatin,1,730,0.000000,1.0,estimable_imprecise


,endpoint,centre,model,explanation_tier,analysis_status,feature_group,n_columns,metric,importance,finite_fraction,reporting_status
1,OS,DFCI,minimal_cox,primary_reference,primary,age_at_folfox,1,730,0.002129,1.0,estimable
4,OS,DFCI,minimal_cox,primary_reference,primary,metastatic_presentation,1,730,0.010953,1.0,estimable
7,OS,DFCI,minimal_cox,primary_reference,primary,ca_d_site,9,730,0.011532,1.0,estimable
10,OS,DFCI,minimal_cox,primary_reference,primary,number_metastatic_sites,1,730,0.005979,1.0,estimable
13,OS,MSK,minimal_cox,primary_reference,primary,age_at_folfox,1,730,0.002994,1.0,estimable
...,...,...,...,...,...,...,...,...,...,...,...
1651,TTNT-D,VICC,reduced_core_penalized_cox,exploratory_supplementary,post_hoc_exploratory,dmets_liver,1,730,0.002906,1.0,estimable_imprecise
1654,TTNT-D,VICC,reduced_core_penalized_cox,exploratory_supplementary,post_hoc_exploratory,dmets_pelvis,1,730,0.001688,1.0,estimable_imprecise
1657,TTNT-D,VICC,reduced_core_penalized_cox,exploratory_supplementary,post_hoc_exploratory,dmets_thorax,1,730,0.015564,1.0,estimable_imprecise
1660,TTNT-D,VICC,reduced_core_penalized_cox,exploratory_supplementary,post_hoc_exploratory,prior_oxaliplatin,1,730,0.000000,1.0,estimable_imprecise


## Grouped spline and partial-effect curves

`spline_cox` and `penalized_nonlinear_cox`'s age partial effects, on the frozen 25-point grid,
with bootstrap-refit bands where available. `penalized_nonlinear_cox` additionally reports one
curve per `metastatic_presentation` level, since the admitted interaction is exactly that.

In [ ]:
display(result.partial_effects.head(50))

## Comparability matrix -- what was and was not compared, and why

Every attempted cross-centre, cross-endpoint, and cross-model comparison, admissible or not.
A `not_comparable` row and every `restricted_scopes`/cross-tier row carrying
`availability_artifact_possible = True` are the machine-readable form of the rule that an
attribution difference coinciding with a fit-availability gap is never read as biological or
institutional heterogeneity.

In [8]:
display(result.comparability_matrix)

refused = result.comparability_matrix[
    result.comparability_matrix["comparison_status"] == "not_comparable"
]
print(f"Refused comparisons: {len(refused)}")
display(refused)

artifact_possible = result.attribution_stability[
    result.attribution_stability["availability_artifact_possible"]
]
print(f"Comparisons flagged availability_artifact_possible: {len(artifact_possible)}")

,comparison_type,model_name,key_a,key_b,scope_basis,availability_confounded,availability_artifact_possible,comparison_status,reason,endpoint
0,cross_centre,minimal_cox,DFCI,MSK,identical_scopes,False,False,comparable,,OS
1,cross_centre,minimal_cox,DFCI,VICC,identical_scopes,False,False,comparable,,OS
2,cross_centre,minimal_cox,MSK,VICC,identical_scopes,False,False,comparable,,OS
3,cross_centre,spline_cox,DFCI,MSK,identical_scopes,False,False,comparable,,OS
4,cross_centre,spline_cox,DFCI,VICC,identical_scopes,False,False,comparable,,OS
5,cross_centre,spline_cox,MSK,VICC,identical_scopes,False,False,comparable,,OS
6,cross_centre,elastic_net_cox,DFCI,MSK,identical_scopes,False,False,comparable,,OS
7,cross_centre,elastic_net_cox,DFCI,VICC,identical_scopes,False,False,comparable,,OS
8,cross_centre,elastic_net_cox,MSK,VICC,identical_scopes,False,False,comparable,,OS
9,cross_centre,glmnet_ridge_core,DFCI,MSK,identical_scopes,False,False,comparable,,OS


Refused comparisons: 2


,comparison_type,model_name,key_a,key_b,scope_basis,availability_confounded,availability_artifact_possible,comparison_status,reason,endpoint
39,cross_centre,reduced_core_penalized_cox,DFCI,MSK,restricted_scopes,True,True,not_comparable,model_unavailable_in_centre,TTNT-D
41,cross_centre,reduced_core_penalized_cox,MSK,VICC,restricted_scopes,True,True,not_comparable,model_unavailable_in_centre,TTNT-D


Comparisons flagged availability_artifact_possible: 37


## Attribution and prediction stability

Cross-centre, cross-endpoint, and cross-model (vs. `minimal_cox`) rank agreement, and
patient-level prediction-stability summaries -- aggregate only, per
`explainability-spec.md`'s E5/E6.

In [9]:
display(result.attribution_stability)
display(result.prediction_stability)
display(result.selection_stability)

,comparison_type,model_name,key_a,key_b,scope_basis,availability_confounded,availability_artifact_possible,comparison_status,reason,kendall_tau,top_k,topk_overlap,jaccard,top_k_boundary_tied,sign_agreement,n_groups,endpoint
0,cross_centre,minimal_cox,DFCI,MSK,identical_scopes,False,False,comparable,,0.333333,2,1.0,0.333333,False,1.000000,4,OS
1,cross_centre,minimal_cox,DFCI,VICC,identical_scopes,False,False,comparable,,-0.333333,2,1.0,0.333333,False,1.000000,4,OS
2,cross_centre,minimal_cox,MSK,VICC,identical_scopes,False,False,comparable,,0.333333,2,1.0,0.333333,False,1.000000,4,OS
3,cross_centre,spline_cox,DFCI,MSK,identical_scopes,False,False,comparable,,0.409524,5,3.0,0.428571,False,0.800000,15,OS
4,cross_centre,spline_cox,DFCI,VICC,identical_scopes,False,False,comparable,,0.257143,5,3.0,0.428571,False,0.933333,15,OS
5,cross_centre,spline_cox,MSK,VICC,identical_scopes,False,False,comparable,,0.085714,5,3.0,0.428571,False,0.866667,15,OS
6,cross_centre,elastic_net_cox,DFCI,MSK,identical_scopes,False,False,comparable,,0.600000,5,4.0,0.666667,False,0.933333,15,OS
7,cross_centre,elastic_net_cox,DFCI,VICC,identical_scopes,False,False,comparable,,0.200000,5,2.0,0.250000,False,0.933333,15,OS
8,cross_centre,elastic_net_cox,MSK,VICC,identical_scopes,False,False,comparable,,0.257143,5,3.0,0.428571,False,1.000000,15,OS
9,cross_centre,glmnet_ridge_core,DFCI,MSK,identical_scopes,False,False,comparable,,0.676190,5,4.0,0.666667,False,0.800000,15,OS


,endpoint,centre,model,horizon,n_patients,n_refits,median_interval_width,q1_interval_width,q3_interval_width,proportion_exceeding_010,proportion_exceeding_020
0,OS,DFCI,minimal_cox,365.0,227,199,0.060304,0.037748,0.085405,0.193833,0.048458
1,OS,DFCI,minimal_cox,730.0,227,199,0.144036,0.098816,0.208951,0.731278,0.281938
2,OS,MSK,minimal_cox,365.0,330,199,0.091166,0.060790,0.129978,0.430303,0.081818
3,OS,MSK,minimal_cox,730.0,330,199,0.231943,0.165747,0.315669,0.939394,0.615152
4,OS,VICC,minimal_cox,365.0,87,199,0.053078,0.037965,0.078720,0.137931,0.011494
5,OS,VICC,minimal_cox,730.0,87,199,0.134121,0.099324,0.183582,0.735632,0.195402
6,TTNT-D,DFCI,minimal_cox,365.0,126,200,0.314508,0.263493,0.352671,1.000000,0.976190
7,TTNT-D,DFCI,minimal_cox,730.0,126,200,0.290488,0.219626,0.346654,0.976190,0.841270
8,TTNT-D,MSK,minimal_cox,365.0,180,190,0.397619,0.351082,0.463453,1.000000,1.000000
9,TTNT-D,MSK,minimal_cox,730.0,180,190,0.326924,0.265316,0.393605,0.972222,0.883333


,endpoint,centre,model,feature_group,selection_frequency
0,OS,DFCI,elastic_net_cox,age_at_folfox,1.000
1,OS,DFCI,elastic_net_cox,naaccr_sex_code,1.000
2,OS,DFCI,elastic_net_cox,race_ethnicity,1.000
3,OS,DFCI,elastic_net_cox,metastatic_presentation,1.000
4,OS,DFCI,elastic_net_cox,crc_type,1.000
5,OS,DFCI,elastic_net_cox,ca_d_site,1.000
6,OS,DFCI,elastic_net_cox,ca_grade,1.000
7,OS,DFCI,elastic_net_cox,dmets_abdomen,1.000
8,OS,DFCI,elastic_net_cox,dmets_bone,1.000
9,OS,DFCI,elastic_net_cox,dmets_brain,1.000


## Explanation scope status, privacy scan, and canonical artifact locations

Every scope carries a terminal status. Tier 4 models (`core_cox`, `flexsurv_rp_spline`) are
always `not_explained`, with their recorded reason and real fit-success counts -- never read as
evidence about any feature.

In [10]:
scope_status_display = result.scope_status.replace({"source_registry": registry_labels})
display(scope_status_display)

not_explained = result.scope_status[result.scope_status["explanation_status"] == "not_explained"]
assert set(not_explained["model"]) == {"core_cox", "flexsurv_rp_spline"}
display(
    not_explained[["endpoint", "centre", "model", "reason", "fit_success_count", "fit_total_count"]]
)

print("Published artifacts:")
for _name, path in sorted(result.artifacts.paths.items()):
    print(f"  {path}")

,endpoint,centre,model,explanation_tier,source_registry,analysis_status,explanation_status,reason,fit_success_count,fit_total_count,n_eligible,n_events,n_event_free
0,OS,DFCI,core_cox,not_explained,frozen model-training results,,not_explained,fit_failed_singular_design,3.0,106.0,NaN,NaN,NaN
1,OS,MSK,core_cox,not_explained,frozen model-training results,,not_explained,fit_failed_singular_design,3.0,106.0,NaN,NaN,NaN
2,OS,VICC,core_cox,not_explained,frozen model-training results,,not_explained,fit_failed_singular_design,3.0,106.0,NaN,NaN,NaN
3,TTNT-D,DFCI,core_cox,not_explained,frozen model-training results,,not_explained,fit_failed_singular_design,3.0,106.0,NaN,NaN,NaN
4,TTNT-D,MSK,core_cox,not_explained,frozen model-training results,,not_explained,fit_failed_singular_design,3.0,106.0,NaN,NaN,NaN
5,TTNT-D,VICC,core_cox,not_explained,frozen model-training results,,not_explained,fit_failed_singular_design,3.0,106.0,NaN,NaN,NaN
6,OS,DFCI,flexsurv_rp_spline,not_explained,exploratory optimization results,,not_explained,fit_instability_explanation_unreliable,24.0,56.0,NaN,NaN,NaN
7,OS,MSK,flexsurv_rp_spline,not_explained,exploratory optimization results,,not_explained,fit_instability_explanation_unreliable,24.0,56.0,NaN,NaN,NaN
8,OS,VICC,flexsurv_rp_spline,not_explained,exploratory optimization results,,not_explained,fit_instability_explanation_unreliable,24.0,56.0,NaN,NaN,NaN
9,TTNT-D,DFCI,flexsurv_rp_spline,not_explained,exploratory optimization results,,not_explained,fit_instability_explanation_unreliable,24.0,56.0,NaN,NaN,NaN


,endpoint,centre,model,reason,fit_success_count,fit_total_count
0,OS,DFCI,core_cox,fit_failed_singular_design,3.0,106.0
1,OS,MSK,core_cox,fit_failed_singular_design,3.0,106.0
2,OS,VICC,core_cox,fit_failed_singular_design,3.0,106.0
3,TTNT-D,DFCI,core_cox,fit_failed_singular_design,3.0,106.0
4,TTNT-D,MSK,core_cox,fit_failed_singular_design,3.0,106.0
5,TTNT-D,VICC,core_cox,fit_failed_singular_design,3.0,106.0
6,OS,DFCI,flexsurv_rp_spline,fit_instability_explanation_unreliable,24.0,56.0
7,OS,MSK,flexsurv_rp_spline,fit_instability_explanation_unreliable,24.0,56.0
8,OS,VICC,flexsurv_rp_spline,fit_instability_explanation_unreliable,24.0,56.0
9,TTNT-D,DFCI,flexsurv_rp_spline,fit_instability_explanation_unreliable,24.0,56.0


Published artifacts:
  /Users/camilasarmiento/Documents/Data Freelancer/portfolio/CRC/analysis/out/current/explainability/attribution_stability.csv
  /Users/camilasarmiento/Documents/Data Freelancer/portfolio/CRC/analysis/out/current/explainability/bootstrap_attribution_stability.csv
  /Users/camilasarmiento/Documents/Data Freelancer/portfolio/CRC/analysis/out/current/explainability/coefficient_paths.csv
  /Users/camilasarmiento/Documents/Data Freelancer/portfolio/CRC/analysis/out/current/explainability/coefficient_summary.csv
  /Users/camilasarmiento/Documents/Data Freelancer/portfolio/CRC/analysis/out/current/explainability/comparability_matrix.csv
  /Users/camilasarmiento/Documents/Data Freelancer/portfolio/CRC/analysis/out/current/explainability/cross_family_prediction_spread.csv
  /Users/camilasarmiento/Documents/Data Freelancer/portfolio/CRC/analysis/out/current/explainability/explainability_manifest.json
  /Users/camilasarmiento/Documents/Data Freelancer/portfolio/CRC/analysis/o

## Secondary research question 2 -- the answer from the explainability analysis

> Are model performance and feature-attribution patterns consistent across institutions and
> between OS and death-inclusive time to next treatment, after accounting for de novo versus
> recurrent presentation and previous oxaliplatin exposure?

The primary attribution evidence is the Tier 1 `minimal_cox` cross-centre and cross-endpoint
agreement above, on the common 730-day prediction-loss scale. VICC's imprecision and
`prior_oxaliplatin`'s instability (19 exposed patients of 678) are **expected, reported
outcomes, not centre-level attribution findings** -- see the interpretation rule (R4) enforced
by the comparability matrix above. No statement here describes an attribution difference as
biological, causal, or institutional heterogeneity.
